In [0]:
%sql

LIST 'abfss://bronze@stcommercesrc.dfs.core.windows.net/order_items/';

path,name,size,modification_time
abfss://bronze@stcommercesrc.dfs.core.windows.net/order_items/data_832919c6-c34b-4a07-b264-cd676e355aa3_38461582-8b6c-4a46-a994-5669ddbcfdf6.parquet,data_832919c6-c34b-4a07-b264-cd676e355aa3_38461582-8b6c-4a46-a994-5669ddbcfdf6.parquet,21842392,1790963744000


In [0]:
display(
    dbutils.fs.ls("abfss://bronze@stcommercesrc.dfs.core.windows.net/order_items/")
)

path,name,size,modificationTime
abfss://bronze@stcommercesrc.dfs.core.windows.net/order_items/data_832919c6-c34b-4a07-b264-cd676e355aa3_38461582-8b6c-4a46-a994-5669ddbcfdf6.parquet,data_832919c6-c34b-4a07-b264-cd676e355aa3_38461582-8b6c-4a46-a994-5669ddbcfdf6.parquet,21842392,1790963744000


In [0]:
df_bronze_order_items = spark.read.format('parquet')\
                                    .option('header',True)\
                                    .option('inferSchema',True)\
                                    .load('abfss://bronze@stcommercesrc.dfs.core.windows.net/order_items/')
display(df_bronze_order_items)

order_item_id,order_id,product_id,quantity,unit_price,discount_amount,tax_amount,line_total,created_at,updated_at
1,27741,913,1,6672.630000000000000000,989.620000000000000000,1022.940000000000000000,6705.950000000000000000,2026-09-20T07:33:32Z,2026-09-27T07:33:32Z
2,56889,1144,1,59308.100000000000000000,8026.750000000000000000,9230.640000000000000000,60511.990000000000000000,2024-06-21T22:43:23Z,2024-07-19T22:43:23Z
3,7038,713,5,23107.620000000000000000,9749.610000000000000000,19041.930000000000000000,124830.420000000000000000,2024-02-08T20:28:06Z,2024-02-08T20:28:06Z
4,42135,1792,2,39153.140000000000000000,7914.500000000000000000,12670.520000000000000000,83062.300000000000000000,2025-03-03T05:50:10Z,2025-03-03T05:50:10Z
5,94604,1629,5,1161.810000000000000000,487.400000000000000000,957.900000000000000000,6279.550000000000000000,2025-01-15T10:13:48Z,2025-01-29T10:13:48Z
6,60440,2279,1,26727.210000000000000000,4056.160000000000000000,4080.790000000000000000,26751.840000000000000000,2024-12-12T17:53:58Z,2024-12-17T17:53:58Z
7,51624,3463,3,7785.310000000000000000,1297.990000000000000000,3970.430000000000000000,26028.370000000000000000,2024-08-04T18:21:03Z,2024-08-10T18:21:03Z
8,69051,838,1,61633.330000000000000000,4683.240000000000000000,10251.020000000000000000,67201.110000000000000000,2024-06-08T05:17:49Z,2024-06-19T05:17:49Z
9,70062,4946,3,16475.930000000000000000,7978.910000000000000000,7460.800000000000000000,48909.680000000000000000,2026-04-27T04:44:17Z,2026-05-20T04:44:17Z
10,85432,4393,1,7902.100000000000000000,1537.930000000000000000,1145.550000000000000000,7509.720000000000000000,2024-05-15T01:18:52Z,2024-05-27T01:18:52Z


In [0]:
%sql

CREATE TABLE ecommerce.bronze.order_items
USING PARQUET
LOCATION 'abfss://bronze@stcommercesrc.dfs.core.windows.net/order_items/';

In [0]:
%sql

SELECT COUNT(*) AS bronze_order_items_count
FROM ecommerce.bronze.order_items;

bronze_order_items_count
300000


In [0]:
%sql

SELECT
    order_item_id,
    COUNT(*) AS occurrence_count
FROM ecommerce.bronze.order_items
GROUP BY order_item_id
HAVING COUNT(*) > 1
ORDER BY occurrence_count DESC;

order_item_id,occurrence_count


In [0]:
%sql

SELECT
    oi.order_id,
    COUNT(*) AS item_count
FROM ecommerce.bronze.order_items oi
LEFT JOIN ecommerce.silver.orders o
    ON oi.order_id = o.order_id
WHERE o.order_id IS NULL
GROUP BY oi.order_id
ORDER BY item_count DESC;

order_id,item_count


In [0]:
%sql

SELECT
    oi.product_id,
    COUNT(*) AS item_count
FROM ecommerce.bronze.order_items oi
LEFT JOIN ecommerce.silver.products p
    ON oi.product_id = p.product_id
WHERE p.product_id IS NULL
GROUP BY oi.product_id
ORDER BY item_count DESC;

product_id,item_count
3998,57


In [0]:
%sql

SELECT *
FROM ecommerce.bronze.products
WHERE product_id = 3998;

product_id,product_name,category_id,category_name,brand,price,cost,stock_quantity,product_status,created_at,updated_at


In [0]:
%sql

SELECT
    order_item_id,
    order_id,
    product_id,
    quantity,
    unit_price,
    discount_amount,
    tax_amount,
    line_total,
    created_at,
    updated_at
FROM ecommerce.bronze.order_items
WHERE product_id = 3998
ORDER BY order_id;

order_item_id,order_id,product_id,quantity,unit_price,discount_amount,tax_amount,line_total,created_at,updated_at
207620,2423,3998,2,52222.140000000000000000,13673.610000000000000000,16338.720000000000000000,107109.390000000000000000,2026-06-19T15:54:56Z,2026-06-22T15:54:56Z
223480,4021,3998,4,52222.140000000000000000,13807.940000000000000000,35114.510000000000000000,230195.130000000000000000,2026-08-07T10:38:06Z,2026-08-19T10:38:06Z
61198,4418,3998,3,52222.140000000000000000,19332.650000000000000000,24720.080000000000000000,162053.850000000000000000,2025-12-10T02:56:33Z,2026-01-01T02:56:33Z
233837,4617,3998,3,52222.140000000000000000,27899.130000000000000000,23178.110000000000000000,151945.400000000000000000,2024-10-15T09:19:54Z,2024-11-01T09:19:54Z
165575,7586,3998,2,52222.140000000000000000,13321.650000000000000000,16402.070000000000000000,107524.700000000000000000,2024-12-29T19:51:48Z,2025-01-07T19:51:48Z
17685,11484,3998,4,52222.140000000000000000,34463.220000000000000000,31396.560000000000000000,205821.900000000000000000,2026-07-30T09:43:06Z,2026-08-14T09:43:06Z
278669,13968,3998,1,52222.140000000000000000,5317.980000000000000000,8442.750000000000000000,55346.910000000000000000,2026-04-27T14:11:48Z,2026-05-23T14:11:48Z
40549,16381,3998,1,52222.140000000000000000,8296.240000000000000000,7906.660000000000000000,51832.560000000000000000,2024-10-22T17:11:08Z,2024-10-27T17:11:08Z
157170,19235,3998,1,52222.140000000000000000,5146.350000000000000000,8473.640000000000000000,55549.430000000000000000,2026-03-25T07:16:16Z,2026-03-25T07:16:16Z
272643,19646,3998,5,52222.140000000000000000,29450.780000000000000000,41698.790000000000000000,273358.710000000000000000,2024-04-15T15:06:49Z,2024-04-27T15:06:49Z


In [0]:
%sql

SELECT
    order_item_id,
    quantity,
    unit_price,
    discount_amount,
    tax_amount,
    line_total,
    ROUND(
        (quantity * unit_price)
        - discount_amount
        + tax_amount,
        2
    ) AS expected_line_total
FROM ecommerce.bronze.order_items
WHERE product_id = 3998
  AND ROUND(
        (quantity * unit_price)
        - discount_amount
        + tax_amount,
        2
      ) <> ROUND(line_total, 2);

order_item_id,quantity,unit_price,discount_amount,tax_amount,line_total,expected_line_total


In [0]:
%sql

SELECT
    COUNT(*) AS negative_quantity_records
FROM ecommerce.bronze.order_items
WHERE quantity < 0;

negative_quantity_records
3


In [0]:
%sql

SELECT
    order_item_id,
    order_id,
    product_id,
    quantity,
    unit_price,
    discount_amount,
    tax_amount,
    line_total,
    created_at,
    updated_at
FROM ecommerce.bronze.order_items
WHERE quantity < 0
ORDER BY order_item_id;

order_item_id,order_id,product_id,quantity,unit_price,discount_amount,tax_amount,line_total,created_at,updated_at
1001,19573,2817,-3,50868.490000000000000000,8396.440000000000000000,16801.300000000000000000,110141.840000000000000000,2025-09-25T18:59:43Z,2025-10-15T18:59:43Z
1002,41554,1167,-3,65197.990000000000000000,4798.380000000000000000,22607.570000000000000000,148205.170000000000000000,2024-05-24T19:05:27Z,2024-06-12T19:05:27Z
1003,24702,1592,-3,32535.400000000000000000,1180.110000000000000000,5643.950000000000000000,36999.240000000000000000,2024-12-15T01:26:51Z,2025-01-09T01:26:51Z


In [0]:
%sql

SELECT
    order_item_id,
    product_id,
    quantity
FROM ecommerce.bronze.order_items
WHERE order_item_id IN (1001, 1002, 1003)
   OR product_id = 3998
ORDER BY order_item_id;

order_item_id,product_id,quantity
225,3998,5
1001,2817,-3
1002,1167,-3
1003,1592,-3
14091,3998,1
17685,3998,4
21385,3998,3
21498,3998,4
34273,3998,3
40549,3998,1


In [0]:
%sql

SELECT
    COUNT(*) AS invalid_quantity_records
FROM ecommerce.bronze.order_items
WHERE quantity IS NULL
   OR quantity <= 0;

invalid_quantity_records
3


In [0]:
%sql

SELECT
    COUNT(*) AS invalid_financial_records
FROM ecommerce.bronze.order_items
WHERE unit_price IS NULL
   OR unit_price < 0
   OR discount_amount IS NULL
   OR discount_amount < 0
   OR tax_amount IS NULL
   OR tax_amount < 0
   OR line_total IS NULL
   OR line_total < 0;

invalid_financial_records
0


In [0]:
%sql

SELECT
    COUNT(*) AS invalid_date_records
FROM ecommerce.bronze.order_items
WHERE created_at IS NULL
   OR updated_at IS NULL
   OR updated_at < created_at;

invalid_date_records
0


In [0]:
%sql

SELECT
    COUNT(*) AS invalid_line_total_records
FROM ecommerce.bronze.order_items
WHERE ROUND(
          (quantity * unit_price)
          - discount_amount
          + tax_amount,
          2
      ) <> ROUND(line_total, 2);

invalid_line_total_records
3


In [0]:
%sql

SELECT
    order_item_id,
    order_id,
    product_id,
    quantity,
    unit_price,
    discount_amount,
    tax_amount,
    line_total,
    ROUND(
        (quantity * unit_price)
        - discount_amount
        + tax_amount,
        2
    ) AS expected_line_total
FROM ecommerce.bronze.order_items
WHERE ROUND(
          (quantity * unit_price)
          - discount_amount
          + tax_amount,
          2
      ) <> ROUND(line_total, 2)
ORDER BY order_item_id;

order_item_id,order_id,product_id,quantity,unit_price,discount_amount,tax_amount,line_total,expected_line_total
1001,19573,2817,-3,50868.490000000000000000,8396.440000000000000000,16801.300000000000000000,110141.840000000000000000,-144200.61
1002,41554,1167,-3,65197.990000000000000000,4798.380000000000000000,22607.570000000000000000,148205.170000000000000000,-177784.78
1003,24702,1592,-3,32535.400000000000000000,1180.110000000000000000,5643.950000000000000000,36999.240000000000000000,-93142.36


In [0]:
%sql

CREATE OR REPLACE TABLE ecommerce.silver.order_items
USING DELTA
AS
SELECT
    order_item_id,
    order_id,
    product_id,
    quantity,
    CAST(unit_price AS DECIMAL(12,2)) AS unit_price,
    CAST(discount_amount AS DECIMAL(12,2)) AS discount_amount,
    CAST(tax_amount AS DECIMAL(12,2)) AS tax_amount,
    CAST(line_total AS DECIMAL(12,2)) AS line_total,
    created_at,
    updated_at
FROM ecommerce.bronze.order_items
WHERE order_item_id IS NOT NULL
  AND order_id IS NOT NULL
  AND product_id IS NOT NULL
  AND quantity > 0
  AND unit_price IS NOT NULL
  AND unit_price >= 0
  AND discount_amount IS NOT NULL
  AND discount_amount >= 0
  AND tax_amount IS NOT NULL
  AND tax_amount >= 0
  AND line_total IS NOT NULL
  AND line_total >= 0
  AND ROUND(
        (quantity * unit_price)
        - discount_amount
        + tax_amount,
        2
      ) = ROUND(line_total, 2)
  AND created_at IS NOT NULL
  AND updated_at IS NOT NULL
  AND updated_at >= created_at;

num_affected_rows,num_inserted_rows


In [0]:
%sql

SELECT
    COUNT(*) AS bronze_count,
    (
        SELECT COUNT(*)
        FROM ecommerce.silver.order_items
    ) AS silver_count,
    COUNT(*) - (
        SELECT COUNT(*)
        FROM ecommerce.silver.order_items
    ) AS rejected_count
FROM ecommerce.bronze.order_items;

bronze_count,silver_count,rejected_count
300000,299997,3


In [0]:
%sql

DESCRIBE TABLE ecommerce.silver.order_items;

col_name,data_type,comment
order_item_id,bigint,null
order_id,bigint,null
product_id,int,null
quantity,int,null
unit_price,"decimal(12,2)",null
discount_amount,"decimal(12,2)",null
tax_amount,"decimal(12,2)",null
line_total,"decimal(12,2)",null
created_at,timestamp,null
updated_at,timestamp,null


In [0]:
%sql

CREATE TABLE ecommerce.silver.order_items_external
USING DELTA
LOCATION 'abfss://silver@stcommercesrc.dfs.core.windows.net/order_items/'
AS
SELECT *
FROM ecommerce.silver.order_items;

num_affected_rows,num_inserted_rows


In [0]:
%sql

SELECT * FROM delta.`abfss://silver@stcommercesrc.dfs.core.windows.net/order_items/`
WHERE quantity > 3

order_item_id,order_id,product_id,quantity,unit_price,discount_amount,tax_amount,line_total,created_at,updated_at
3,7038,713,5,23107.62,9749.61,19041.93,124830.42,2024-02-08T20:28:06Z,2024-02-08T20:28:06Z
5,94604,1629,5,1161.81,487.40,957.90,6279.55,2025-01-15T10:13:48Z,2025-01-29T10:13:48Z
14,99150,828,4,6231.74,1385.81,4237.41,27778.56,2024-02-16T06:55:15Z,2024-03-07T06:55:15Z
16,32059,585,5,72238.36,45869.79,56757.96,372079.97,2024-12-05T15:24:52Z,2024-12-22T15:24:52Z
23,1439,4599,5,54134.52,14223.39,46160.86,302610.07,2026-04-26T12:53:27Z,2026-05-14T12:53:27Z
24,8752,4781,4,49255.22,14264.17,32896.21,215652.92,2025-10-13T16:49:57Z,2025-10-17T16:49:57Z
27,1703,521,4,24161.11,7376.28,16068.27,105336.43,2026-07-04T09:25:01Z,2026-07-18T09:25:01Z
28,81964,2060,5,67230.91,57871.00,50091.04,328374.59,2025-03-08T03:42:04Z,2025-03-08T03:42:04Z
29,70826,939,5,21050.17,15806.11,16100.05,105544.79,2024-01-11T02:17:28Z,2024-02-04T02:17:28Z
33,4355,4159,5,2392.93,475.98,2067.96,13556.63,2025-03-07T15:47:40Z,2025-03-18T15:47:40Z


In [0]:
%sql

SELECT COUNT(*) AS total_order_items
FROM ecommerce.silver.order_items_external;

total_order_items
299997


In [0]:
%sql

DESCRIBE HISTORY ecommerce.silver.order_items_external;

version,timestamp,userId,userName,operation,operationParameters,job,notebook,clusterId,readVersion,isolationLevel,isBlindAppend,operationMetrics,userMetadata,engineInfo
0,2026-10-03T08:54:32Z,148417918535894,saireddy12315_outlook.com#ext#@saireddy12315outlook.onmicrosoft.com,CREATE TABLE AS SELECT,"Map(partitionBy -> [], clusterBy -> [], description -> null, isManaged -> false, properties -> {""delta.enableDeletionVectors"":""true""}, statsOnLoad -> true)",null,List(4143522224504329),1003-052435-xepp1xgc,null,WriteSerializable,true,"Map(numFiles -> 1, numOutputRows -> 299997, numOutputBytes -> 13765693)",null,Databricks-Runtime/17.3.x-photon-scala2.13


In [0]:
%sql

CREATE OR REPLACE TABLE ecommerce.silver.order_item_quarantine
USING DELTA
AS
SELECT
    order_item_id,
    order_id,
    product_id,
    quantity,
    CAST(unit_price AS DECIMAL(12,2)) AS unit_price,
    CAST(discount_amount AS DECIMAL(12,2)) AS discount_amount,
    CAST(tax_amount AS DECIMAL(12,2)) AS tax_amount,
    CAST(line_total AS DECIMAL(12,2)) AS line_total,
    created_at,
    updated_at,

    CASE
        WHEN quantity <= 0
             AND ROUND(
                 (quantity * unit_price)
                 - discount_amount
                 + tax_amount,
                 2
             ) <> ROUND(line_total, 2)
            THEN 'INVALID_QUANTITY;LINE_TOTAL_MISMATCH'

        WHEN quantity <= 0
            THEN 'INVALID_QUANTITY'

        WHEN ROUND(
                 (quantity * unit_price)
                 - discount_amount
                 + tax_amount,
                 2
             ) <> ROUND(line_total, 2)
            THEN 'LINE_TOTAL_MISMATCH'

        ELSE 'OTHER_DATA_QUALITY_FAILURE'
    END AS exception_reason,

    CURRENT_TIMESTAMP() AS quarantined_at

FROM ecommerce.bronze.order_items

WHERE quantity <= 0

   OR ROUND(
        (quantity * unit_price)
        - discount_amount
        + tax_amount,
        2
      ) <> ROUND(line_total, 2);

num_affected_rows,num_inserted_rows


In [0]:
%sql

SELECT
    exception_reason,
    COUNT(*) AS record_count
FROM ecommerce.silver.order_item_quarantine
GROUP BY exception_reason
ORDER BY record_count DESC;

exception_reason,record_count
INVALID_QUANTITY;LINE_TOTAL_MISMATCH,3


In [0]:
%sql

CREATE OR REPLACE TABLE ecommerce.silver.order_item_product_exceptions
USING DELTA
AS
SELECT
    oi.order_item_id,
    oi.order_id,
    oi.product_id,
    oi.quantity,
    CAST(oi.unit_price AS DECIMAL(12,2)) AS unit_price,
    CAST(oi.discount_amount AS DECIMAL(12,2)) AS discount_amount,
    CAST(oi.tax_amount AS DECIMAL(12,2)) AS tax_amount,
    CAST(oi.line_total AS DECIMAL(12,2)) AS line_total,
    oi.created_at,
    oi.updated_at,

    'MISSING_PRODUCT_MASTER' AS exception_reason,
    CURRENT_TIMESTAMP() AS exception_detected_at

FROM ecommerce.silver.order_items oi

LEFT JOIN ecommerce.silver.products p
    ON oi.product_id = p.product_id

WHERE p.product_id IS NULL;

num_affected_rows,num_inserted_rows


In [0]:
%sql

SELECT
    exception_reason,
    COUNT(*) AS record_count
FROM ecommerce.silver.order_item_product_exceptions
GROUP BY exception_reason;

exception_reason,record_count
MISSING_PRODUCT_MASTER,57


In [0]:
%sql

CREATE OR REPLACE TABLE ecommerce.silver.order_item_quality_metrics
USING DELTA
AS
SELECT
    CURRENT_TIMESTAMP() AS validation_timestamp,

    (SELECT COUNT(*)
     FROM ecommerce.bronze.order_items) AS bronze_records,

    (SELECT COUNT(*)
     FROM ecommerce.silver.order_items) AS silver_records,

    (SELECT COUNT(*)
     FROM ecommerce.silver.order_item_quarantine) AS hard_rejected_records,

    (SELECT COUNT(*)
     FROM ecommerce.silver.order_item_product_exceptions) AS missing_product_records,

    ROUND(
        (
            (SELECT COUNT(*)
             FROM ecommerce.silver.order_items)
            * 100.0
        )
        /
        (SELECT COUNT(*)
         FROM ecommerce.bronze.order_items),
        2
    ) AS hard_validation_quality_percentage;

num_affected_rows,num_inserted_rows


In [0]:
%sql

SELECT *
FROM ecommerce.silver.order_item_quality_metrics;

validation_timestamp,bronze_records,silver_records,hard_rejected_records,missing_product_records,hard_validation_quality_percentage
2026-10-03T08:58:52.41536Z,300000,299997,3,57,100.00


In [0]:
%sql

SHOW TABLES IN ecommerce.bronze;

database,tableName,isTemporary
bronze,customers,false
bronze,order_items,false
bronze,orders,false
bronze,products,false
,_sqldf,true


In [0]:
%sql
SELECT * FROM delta.`abfss://silver@stcommercesrc.dfs.core.windows.net/order_items/`

order_item_id,order_id,product_id,quantity,unit_price,discount_amount,tax_amount,line_total,created_at,updated_at
1,27741,913,1,6672.63,989.62,1022.94,6705.95,2026-09-20T07:33:32.000Z,2026-09-27T07:33:32.000Z
2,56889,1144,1,59308.10,8026.75,9230.64,60511.99,2024-06-21T22:43:23.000Z,2024-07-19T22:43:23.000Z
3,7038,713,5,23107.62,9749.61,19041.93,124830.42,2024-02-08T20:28:06.000Z,2024-02-08T20:28:06.000Z
4,42135,1792,2,39153.14,7914.50,12670.52,83062.30,2025-03-03T05:50:10.000Z,2025-03-03T05:50:10.000Z
5,94604,1629,5,1161.81,487.40,957.90,6279.55,2025-01-15T10:13:48.000Z,2025-01-29T10:13:48.000Z
6,60440,2279,1,26727.21,4056.16,4080.79,26751.84,2024-12-12T17:53:58.000Z,2024-12-17T17:53:58.000Z
7,51624,3463,3,7785.31,1297.99,3970.43,26028.37,2024-08-04T18:21:03.000Z,2024-08-10T18:21:03.000Z
8,69051,838,1,61633.33,4683.24,10251.02,67201.11,2024-06-08T05:17:49.000Z,2024-06-19T05:17:49.000Z
9,70062,4946,3,16475.93,7978.91,7460.80,48909.68,2026-04-27T04:44:17.000Z,2026-05-20T04:44:17.000Z
10,85432,4393,1,7902.10,1537.93,1145.55,7509.72,2024-05-15T01:18:52.000Z,2024-05-27T01:18:52.000Z
